In [1]:
import pandas as pd
import requests
import json
import numpy as np

In [2]:
!pwd

/home/sinpea/XAI-miniproj/Grepo/fish-vista/notebook


In [3]:
!find . -name "identification*"

./identification_test_manual_annot.csv
./identification_train.csv
./identification_test_lvsp.csv
./identification_val.csv
./identification_test_insp.csv


In [4]:
!find . -name "classification*"

./classification_train.csv
./classification_val.csv
./classification_test.csv


In [5]:
df_clsf_train = pd.read_csv("classification_train.csv")
df_clsf_test = pd.read_csv("classification_train.csv")
df_clsf_val = pd.read_csv("classification_val.csv")
df_idf_train = pd.read_csv("identification_train.csv")

/tmp/ipykernel_16654/3054484276.py:1: DtypeWarning: Columns (0: verbatim_species, 1: species) have mixed types. Specify dtype option on import or set low_memory=False.
  df_clsf_train = pd.read_csv("classification_train.csv")
/tmp/ipykernel_16654/3054484276.py:2: DtypeWarning: Columns (0: verbatim_species, 1: species) have mixed types. Specify dtype option on import or set low_memory=False.
  df_clsf_test = pd.read_csv("classification_train.csv")


In [6]:
df_idf_train.head()

,filename,source_filename,original_format,arkid,family,source,owner,standardized_species,adipose_fin,pelvic_fin,barbel,multiple_dorsal_fin,original_url,license,file_name
0,INHS_FISH_48507.jpg,INHS_FISH_48507.jpg,jpg,tb32dh83,Cyprinidae,GLIN,INHS,phenacobius mirabilis,0,1,1.0,0,https://fishair.org/hdr-share/ftp/ark/89609/GL...,CC BY-NC,Images/chunk_2/INHS_FISH_48507.jpg
1,OSUM0005745_1.jpg,OSUM0005745.JPG,jpg,sg46jm52,Cyprinidae,GLIN,OSUM,phenacobius uranops,0,1,1.0,0,https://fishair.org/hdr-share/ftp/ark/89609/GL...,CC0 1.0,Images/chunk_2/OSUM0005745_1.jpg
2,INHS_FISH_33088.jpg,INHS_FISH_33088.jpg,jpg,3m99vd20,Centrarchidae,GLIN,INHS,lepomis megalotis,0,1,0.0,0,https://fishair.org/hdr-share/ftp/ark/89609/GL...,CC BY-NC,Images/chunk_2/INHS_FISH_33088.jpg
3,JFBM-FISH-0022382.jpg,JFBM-FISH-0022382.jpg,jpg,7s78bc9j,Cyprinidae,GLIN,JFBM,notropis texanus,0,1,0.0,0,https://fishair.org/hdr-share/ftp/ark/89609/GL...,CC0 1.0,Images/chunk_2/JFBM-FISH-0022382.jpg
4,INHS_FISH_1833.jpg,INHS_FISH_1833.jpg,jpg,d565dj7v,Cyprinidae,GLIN,INHS,notropis stramineus,0,1,0.0,0,https://fishair.org/hdr-share/ftp/ark/89609/GL...,CC BY-NC,Images/chunk_1/INHS_FISH_1833.jpg


# features already present in classification:
- adipose_fin presence
- pelvic_fin presence
- barbel presence
- multiple_dorsal_fin presence

# next on agenda:
- get the unique values

In [7]:
adipose_fin_values = df_idf_train["adipose_fin"].unique()

In [8]:
adipose_fin_values

array([0, 1])

In [9]:
pelvic_fin_values = df_idf_train["pelvic_fin"].unique()

In [10]:
pelvic_fin_values

array([1, 0])

In [11]:
barbel_values = df_idf_train["barbel"].unique()

In [12]:
barbel_values

array([1., 0.])

In [13]:
multiple_dorsal_fin_values = df_idf_train["multiple_dorsal_fin"].unique()

In [14]:
multiple_dorsal_fin_values

array([0, 1])

In [15]:
species_list_idf_train = df_idf_train["standardized_species"].unique().tolist()

In [16]:
# now look through fishBase
!ls FishBase

morphdat.parquet  species.parquet


In [17]:
df_fb_spcs = pd.read_parquet("FishBase/species.parquet")
df_fb_mrph = pd.read_parquet("FishBase/morphdat.parquet")

In [18]:
df_fb_mrph.columns.tolist()

['autoctr',
 'Speccode',
 'StockCode',
 'MorphDatRefNo',
 'Females',
 'Males',
 'AppearancePic',
 'SexualAttributes',
 'SexMorphology',
 'SexColors',
 'StrikingFeatures',
 'BodyShapeI',
 'BodyShapeII',
 'Forehead',
 'OperculumPresent',
 'TypeofEyes',
 'TypeofMouth',
 'PosofMouth',
 'MandibleTeeth',
 'MandibleTeethT1',
 'MandibleTeethT2',
 'MandibleRowsMin',
 'MandibleRowsMax',
 'MaxillaTeeth',
 'MaxillaTeethT1',
 'MaxillaTeethT2',
 'MaxillaRowsMin',
 'MaxillaRowsMax',
 'VomerineTeeth',
 'VomerineTeethT1',
 'VomerineTeethT2',
 'VomerineRowsMin',
 'VomerineRowsMax',
 'Palatine',
 'PalatineTeethT1',
 'PalatineTeethT2',
 'PalatineRowsMin',
 'PalatineRowsMax',
 'PharyngealTeeth',
 'PharyngealTeethT1',
 'PharyngealTeethT2',
 'PharyngealRowsMin',
 'PharyngealRowsMax',
 'TeethonTongue',
 'Lipsteeth',
 'DermalTeeth',
 'CommentonTeeth',
 'TypeofScales',
 'Scutes',
 'Keels',
 'HorStripesTTI',
 'HorStripesTTII',
 'VerStripesTTI',
 'VerStripesTTII',
 'VerStripesTTIII',
 'DiaStripesTTI',
 'DiaStripe

In [19]:
df_fb_spcs.columns.tolist()

['SpecCode',
 'Genus',
 'Species',
 'SpeciesRefNo',
 'Author',
 'FBname',
 'PicPreferredName',
 'PicPreferredNameM',
 'PicPreferredNameF',
 'PicPreferredNameJ',
 'FamCode',
 'Subfamily',
 'GenCode',
 'SubGenCode',
 'BodyShapeI',
 'Source',
 'AuthorRef',
 'Remark',
 'TaxIssue',
 'Fresh',
 'Brack',
 'Saltwater',
 'DemersPelag',
 'AirBreathing',
 'AirBreathingRef',
 'AnaCat',
 'MigratRef',
 'DepthRangeShallow',
 'DepthRangeDeep',
 'DepthRangeRef',
 'DepthRangeComShallow',
 'DepthRangeComDeep',
 'DepthComRef',
 'LongevityWild',
 'LongevityWildRef',
 'LongevityCaptive',
 'LongevityCapRef',
 'Vulnerability',
 'VulnerabilityClimate',
 'Length',
 'LTypeMaxM',
 'LengthFemale',
 'LTypeMaxF',
 'MaxLengthRef',
 'CommonLength',
 'LTypeComM',
 'CommonLengthF',
 'LTypeComF',
 'CommonLengthRef',
 'Weight',
 'WeightFemale',
 'MaxWeightRef',
 'Pic',
 'PictureFemale',
 'LarvaPic',
 'EggPic',
 'ImportanceRef',
 'Importance',
 'PriceCateg',
 'PriceReliability',
 'Remarks7',
 'LandingStatistics',
 'Landings

In [20]:
df_fb_mrph.head()

,autoctr,Speccode,StockCode,MorphDatRefNo,Females,Males,AppearancePic,SexualAttributes,SexMorphology,SexColors,...,RemarkSex,AddChars,SimilarSpecies1,SimilarSpec1Remarks,SimilarSpecies2,SimilarSpec2Remarks,EaseofID,OtherRef1,OtherRef2,TS
0,80,2,1,2.0,-1,-1,ORNIL_U0,NaN,different morphology during breeding season only,different colors during breeding season only,...,NaN,"Diagnosis: A large deep-bodied tilapia, with a...",NaN,NaN,NaN,NaN,NaN,53405.0,NaN,NaT
1,81,3,3,2.0,-1,-1,ORMOS_M0,no special organs,always different morphology between mature adults,NaN,...,"Jaw structure (premaxilla width and length, mo...",NaN,NaN,NaN,NaN,NaN,NaN,2847.0,57928.0,NaT
2,82,4,4,20.0,-1,-1,ENRIN_U0,no special organs,males alike females,males alike females,...,NaN,"Body elongate, slender, and rounded in cross s...",NaN,NaN,NaN,NaN,NaN,55763.0,NaN,NaT
3,83,5,5,78464.0,0,0,NaN,no special organs,males alike females,males alike females,...,NaN,Back elevated; snout long and tapering. Mouth...,NaN,NaN,NaN,NaN,NaN,25.0,NaN,NaT
4,22571,67837,6,105887.0,0,0,NaN,NaN,NaN,NaN,...,NaN,This species is distinguished by the following...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaT


In [21]:
# for i in species_list_idf_train:
def get_speccode(spcs):
    try:
        genus,species = spcs.split()[:2]
        spec_df = df_fb_spcs['SpecCode'][(df_fb_spcs['Genus'].str.lower() == genus.lower()) & (df_fb_spcs['Species'].str.lower() == species.lower())]
        # print(spec_df)
        return int(spec_df.iloc[0])
    except Exception as e:
        print(e)
        return None

In [22]:
def get_morph_data(speccode):
    # just get the data for each species and then we will see
    try:
        morph_df = df_fb_mrph[(df_fb_mrph['Speccode'] == speccode)]
        return morph_df
    except Exception as e:
        print(e)
        return None

In [23]:
# get all possible fishbase data for all species
data_fishBase = {}
no_fishBase = [] # those which dont have speccode in FishBase
no_fish = [] # species not in fishBase
partial_fishBase = [] # species that are partially present

```
{
    "Whole Body": [
        "StrikingFeatures",
        "BodyShapeI",
        "BodyShapeII",
        "StandardLengthCm",
        "Forklength",
        "Totallength",
        "PreDorsalLength",
        "PrePelvicsLength",
        "PreAnalLength",
        "PostHeadDepth",
        "PostTrunkDepth",
        "MaximumDepth"
    ],
    "Head": [
        "Forehead",
        "HeadLength",
        "PreorbitalLength"
    ],
    "Barbels":[
        "BarbelsNo",
        "BarbelsType"
    ],
    "Eyes": [
        "TypeofEyes",
        "EyeLength"
    ],
    "Mouth and Teeth": [
        "TypeofMouth",
        "PosofMouth",
        "MandibleTeeth",
        "MandibleTeethT1",
        "MandibleTeethT2",
        "MandibleRowsMin",
        "MandibleRowsMax",
        "MaxillaTeeth",
        "MaxillaTeethT1",
        "MaxillaTeethT2",
        "MaxillaRowsMin",
        "MaxillaRowsMax",
        "VomerineTeeth",
        "VomerineTeethT1",
        "VomerineTeethT2",
        "VomerineRowsMin",
        "VomerineRowsMax",
        "Palatine",
        "PalatineTeethT1",
        "PalatineTeethT2",
        "PalatineRowsMin",
        "PalatineRowsMax",
        "PharyngealTeeth",
        "PharyngealTeethT1",
        "PharyngealTeethT2",
        "PharyngealRowsMin",
        "PharyngealRowsMax",
        "TeethonTongue",
        "Lipsteeth",
        "CommentonTeeth"
    ],
    "Gills": [
        "OperculumPresent",
        "GillCleftsNo",
        "Spiracle",
        "GillRakersLowMin",
        "GillRakersLowMax",
        "GillRakersUpMin",
        "GillRakersUpMax",
        "GillRakersTotalMin",
        "GillRakersTotalMax"
    ],
    "Skin, Scales and Coloration": [
        "DermalTeeth",
        "TypeofScales",
        "Scutes",
        "Keels",
        "HorStripesTTI",
        "HorStripesTTII",
        "VerStripesTTI",
        "VerStripesTTII",
        "VerStripesTTIII",
        "DiaStripesTTI",
        "DiaStripesTTII",
        "DiaStripesTTIII",
        "CurStripesTTI",
        "CurStripesTTII",
        "CurStripesTTIII",
        "SpotsTTI",
        "SpotsTTII",
        "SpotsTTIII",
        "LateralLinesNo",
        "LLinterrupted",
        "ScalesLateralmin",
        "ScalesLateralmax",
        "PoredScalesMin",
        "PoredScalesMax",
        "LatSeriesMin",
        "LatSeriesMax",
        "ScaleRowsAboveMin",
        "ScaleRowsAboveMax",
        "ScaleRowsBelowMin",
        "ScaleRowsBelowMax",
        "ScalesPeduncMin",
        "ScalesPeduncMax"
    ],
    "Dorsal Fin": [
        "DorsalFinI",
        "DorsalFinII",
        "DorsalAttributes",
        "Dfinno",
        "DorsalSpinesMin",
        "DorsalSpinesMax",
        "Notched",
        "DorsalSoftRaysMin",
        "DorsalSoftRaysMax",
        "DFinletsmin",
        "DFinletsmax"
    ],
    "Adipose Fin":[
        "Adifin"
    ],
    "Caudal Fin": [
        "CaudalFinI",
        "CaudalFinII",
        "CShape",
        "CaudalHeight",
        "PeduncleDepth",
        "PeduncleLength"
    ],
    "Anal Fin": [
        "AnalFinI",
        "AnalFinII",
        "Afinno",
        "AnalFinSpinesMin",
        "AnalFinSpinesMax",
        "Araymin",
        "Araymax"
    ],
    "Pectoral Fins": [
        "PectoralAttributes",
        "Pspines2",
        "Praymin",
        "Praymax"
    ],
    "Pelvic Fins": [
        "PelvicsAttributes",
        "VPosition",
        "VPosition2",
        "Vspines",
        "Vraymin",
        "Vraymax",
        "VFinletsmin",
        "VFinletsmax"
    ],
    "Internal Anatomy": [
        "Vertebrae",
        "VertebraePreanMin",
        "VertebraePreanMax",
        "VertebraeTotalMin",
        "VertebraeTotalMax",
        "GasBladder"
    ],
    "Sex and Reproduction": [
        "Females",
        "Males",
        "SexualAttributes",
        "SexMorphology",
        "SexColors",
        "RemarkSex"
    ],
    "misc": [
        "autoctr",
        "Speccode",
        "StockCode",
        "MorphDatRefNo",
        "AppearancePic",
        "Attributes",
        "Entered",
        "DateEntered",
        "Modified",
        "DateModified",
        "Expert",
        "DateChecked",
        "AddChars",
        "SimilarSpecies1",
        "SimilarSpec1Remarks",
        "SimilarSpecies2",
        "SimilarSpec2Remarks",
        "EaseofID",
        "OtherRef1",
        "OtherRef2",
        "TS"
    ]
}

In [24]:
for i in species_list_idf_train:
    speccode = get_speccode(i)
    if(speccode == None):
        no_fish.append(i)
        continue
    morph_data = get_morph_data(speccode)
    
    # check if it is empty or not
    json_val = json.loads(morph_data.to_json(orient='records'))
    if(len(json_val) >= 1):
        data_fishBase[i] = json_val[0]
    else:
        no_fish.append(i)

/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9

single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds


/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9

single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds
single positional indexer is out-of-bounds


/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9

...

/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9

single positional indexer is out-of-bounds
single positional indexer is out-of-bounds


/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9

single positional indexer is out-of-bounds


/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/4209049553.py:9

In [25]:
data_fishBase

{'phenacobius mirabilis': {'autoctr': 22743,
  'Speccode': 2923,
  'StockCode': 3119,
  'MorphDatRefNo': 86798.0,
  'Females': 0,
  'Males': 0,
  'AppearancePic': None,
  'SexualAttributes': None,
  'SexMorphology': None,
  'SexColors': None,
  'StrikingFeatures': None,
  'BodyShapeI': 'elongated',
  'BodyShapeII': None,
  'Forehead': None,
  'OperculumPresent': 0,
  'TypeofEyes': None,
  'TypeofMouth': None,
  'PosofMouth': None,
  'MandibleTeeth': None,
  'MandibleTeethT1': None,
  'MandibleTeethT2': None,
  'MandibleRowsMin': None,
  'MandibleRowsMax': None,
  'MaxillaTeeth': None,
  'MaxillaTeethT1': None,
  'MaxillaTeethT2': None,
  'MaxillaRowsMin': None,
  'MaxillaRowsMax': None,
  'VomerineTeeth': None,
  'VomerineTeethT1': None,
  'VomerineTeethT2': None,
  'VomerineRowsMin': None,
  'VomerineRowsMax': None,
  'Palatine': None,
  'PalatineTeethT1': None,
  'PalatineTeethT2': None,
  'PalatineRowsMin': None,
  'PalatineRowsMax': None,
  'PharyngealTeeth': None,
  'PharyngealTee

In [26]:
len(no_fish)

200

In [27]:
len(data_fishBase)

428

In [28]:
# get all unique values for each field with no. of occurances
unique_values = {}
for i in data_fishBase:
    for j in data_fishBase[i]:
        if j not in unique_values:
            unique_values[j] = {}

        if(str(data_fishBase[i][j]) not in unique_values[j]):
            unique_values[j][str(data_fishBase[i][j])] = 0

        unique_values[j][str(data_fishBase[i][j])] += 1

In [29]:
unique_values

{'autoctr': {'22743': 1,
  '1811': 1,
  '2157': 1,
  '1992': 1,
  '2156': 1,
  '267': 1,
  '2154': 1,
  '2091': 1,
  '18808': 1,
  '2504': 1,
  '19107': 1,
  '19161': 1,
  '1956': 1,
  '2005': 1,
  '249': 1,
  '1131': 1,
  '19106': 1,
  '18806': 1,
  '1991': 1,
  '22469': 1,
  '2155': 1,
  '1894': 1,
  '18876': 1,
  '278': 1,
  '2006': 1,
  '2007': 1,
  '857': 1,
  '250': 1,
  '5987': 1,
  '1254': 1,
  '22452': 1,
  '16791': 1,
  '3067': 1,
  '19105': 1,
  '22746': 1,
  '2008': 1,
  '1994': 1,
  '1249': 1,
  '1993': 1,
  '22451': 1,
  '18809': 1,
  '3449': 1,
  '18961': 1,
  '6643': 1,
  '333': 1,
  '21668': 1,
  '254': 1,
  '1990': 1,
  '255': 1,
  '1938': 1,
  '1988': 1,
  '3016': 1,
  '253': 1,
  '21665': 1,
  '2503': 1,
  '2000': 1,
  '856': 1,
  '1824': 1,
  '12347': 1,
  '1197': 1,
  '809': 1,
  '4028': 1,
  '2722': 1,
  '18920': 1,
  '18787': 1,
  '8062': 1,
  '277': 1,
  '1485': 1,
  '3666': 1,
  '3778': 1,
  '6339': 1,
  '2678': 1,
  '3473': 1,
  '3578': 1,
  '15715': 1,
  '14

In [30]:
with open('out_fb_unt1.json','w') as f:
    json.dump(data_fishBase,f)

with open('out_unique_unt1.json','w') as f:
    json.dump(unique_values,f)

with open('out_nodata_unt1.json','w') as f:
    json.dump(no_fish,f)

In [31]:
# reorganize the fishBase into a more modular form
schema = {
    "Whole Body": [
        "StrikingFeatures",
        "BodyShapeI",
        "BodyShapeII",
        "StandardLengthCm",
        "Forklength",
        "Totallength",
        "PreDorsalLength",
        "PrePelvicsLength",
        "PreAnalLength",
        "PostHeadDepth",
        "PostTrunkDepth",
        "MaximumDepth"
    ],
    "Head": [
        "Forehead",
        "HeadLength",
        "PreorbitalLength"
    ],
    "Barbels":[
        "BarbelsNo",
        "BarbelsType"
    ],
    "Eyes": [
        "TypeofEyes",
        "EyeLength"
    ],
    "Mouth and Teeth": [
        "TypeofMouth",
        "PosofMouth",
        "MandibleTeeth",
        "MandibleTeethT1",
        "MandibleTeethT2",
        "MandibleRowsMin",
        "MandibleRowsMax",
        "MaxillaTeeth",
        "MaxillaTeethT1",
        "MaxillaTeethT2",
        "MaxillaRowsMin",
        "MaxillaRowsMax",
        "VomerineTeeth",
        "VomerineTeethT1",
        "VomerineTeethT2",
        "VomerineRowsMin",
        "VomerineRowsMax",
        "Palatine",
        "PalatineTeethT1",
        "PalatineTeethT2",
        "PalatineRowsMin",
        "PalatineRowsMax",
        "PharyngealTeeth",
        "PharyngealTeethT1",
        "PharyngealTeethT2",
        "PharyngealRowsMin",
        "PharyngealRowsMax",
        "TeethonTongue",
        "Lipsteeth",
        "CommentonTeeth"
    ],
    "Gills": [
        "OperculumPresent",
        "GillCleftsNo",
        "Spiracle",
        "GillRakersLowMin",
        "GillRakersLowMax",
        "GillRakersUpMin",
        "GillRakersUpMax",
        "GillRakersTotalMin",
        "GillRakersTotalMax"
    ],
    "Skin, Scales and Coloration": [
        "DermalTeeth",
        "TypeofScales",
        "Scutes",
        "Keels",
        "HorStripesTTI",
        "HorStripesTTII",
        "VerStripesTTI",
        "VerStripesTTII",
        "VerStripesTTIII",
        "DiaStripesTTI",
        "DiaStripesTTII",
        "DiaStripesTTIII",
        "CurStripesTTI",
        "CurStripesTTII",
        "CurStripesTTIII",
        "SpotsTTI",
        "SpotsTTII",
        "SpotsTTIII",
        "LateralLinesNo",
        "LLinterrupted",
        "ScalesLateralmin",
        "ScalesLateralmax",
        "PoredScalesMin",
        "PoredScalesMax",
        "LatSeriesMin",
        "LatSeriesMax",
        "ScaleRowsAboveMin",
        "ScaleRowsAboveMax",
        "ScaleRowsBelowMin",
        "ScaleRowsBelowMax",
        "ScalesPeduncMin",
        "ScalesPeduncMax"
    ],
    "Dorsal Fin": [
        "DorsalFinI",
        "DorsalFinII",
        "DorsalAttributes",
        "Dfinno",
        "DorsalSpinesMin",
        "DorsalSpinesMax",
        "Notched",
        "DorsalSoftRaysMin",
        "DorsalSoftRaysMax",
        "DFinletsmin",
        "DFinletsmax"
    ],
    "Adipose Fin":[
        "Adifin"
    ],
    "Caudal Fin": [
        "CaudalFinI",
        "CaudalFinII",
        "CShape",
        "CaudalHeight",
        "PeduncleDepth",
        "PeduncleLength"
    ],
    "Anal Fin": [
        "AnalFinI",
        "AnalFinII",
        "Afinno",
        "AnalFinSpinesMin",
        "AnalFinSpinesMax",
        "Araymin",
        "Araymax"
    ],
    "Pectoral Fins": [
        "PectoralAttributes",
        "Pspines2",
        "Praymin",
        "Praymax"
    ],
    "Pelvic Fins": [
        "PelvicsAttributes",
        "VPosition",
        "VPosition2",
        "Vspines",
        "Vraymin",
        "Vraymax",
        "VFinletsmin",
        "VFinletsmax"
    ],
    "Internal Anatomy": [
        "Vertebrae",
        "VertebraePreanMin",
        "VertebraePreanMax",
        "VertebraeTotalMin",
        "VertebraeTotalMax",
        "GasBladder"
    ],
    "Sex and Reproduction": [
        "Females",
        "Males",
        "SexualAttributes",
        "SexMorphology",
        "SexColors",
        "RemarkSex"
    ],
    "misc": [
        "autoctr",
        "Speccode",
        "StockCode",
        "MorphDatRefNo",
        "AppearancePic",
        "Attributes",
        "Entered",
        "DateEntered",
        "Modified",
        "DateModified",
        "Expert",
        "DateChecked",
        "AddChars",
        "SimilarSpecies1",
        "SimilarSpec1Remarks",
        "SimilarSpecies2",
        "SimilarSpec2Remarks",
        "EaseofID",
        "OtherRef1",
        "OtherRef2",
        "TS"
    ]
}

struct_data_fishBase = {}

for species in data_fishBase:
    struct_data_fishBase[species] = {}
    for i in schema:
        struct_data_fishBase[species][i] = {}
        for j in schema[i]:
            struct_data_fishBase[species][i][j] = data_fishBase[species][j]

In [32]:
struct_data_fishBase

{'phenacobius mirabilis': {'Whole Body': {'StrikingFeatures': None,
   'BodyShapeI': 'elongated',
   'BodyShapeII': None,
   'StandardLengthCm': None,
   'Forklength': None,
   'Totallength': None,
   'PreDorsalLength': None,
   'PrePelvicsLength': None,
   'PreAnalLength': None,
   'PostHeadDepth': None,
   'PostTrunkDepth': None,
   'MaximumDepth': None},
  'Head': {'Forehead': None, 'HeadLength': None, 'PreorbitalLength': None},
  'Barbels': {'BarbelsNo': None, 'BarbelsType': None},
  'Eyes': {'TypeofEyes': None, 'EyeLength': None},
  'Mouth and Teeth': {'TypeofMouth': None,
   'PosofMouth': None,
   'MandibleTeeth': None,
   'MandibleTeethT1': None,
   'MandibleTeethT2': None,
   'MandibleRowsMin': None,
   'MandibleRowsMax': None,
   'MaxillaTeeth': None,
   'MaxillaTeethT1': None,
   'MaxillaTeethT2': None,
   'MaxillaRowsMin': None,
   'MaxillaRowsMax': None,
   'VomerineTeeth': None,
   'VomerineTeethT1': None,
   'VomerineTeethT2': None,
   'VomerineRowsMin': None,
   'Vomerin

In [33]:
percentage_analysis = []

for i in unique_values:
    if "None" in unique_values[i] :
        print("percentage of none in ",i," : ",(float(unique_values[i]["None"])/428)*100)

percentage of none in  MorphDatRefNo  :  8.177570093457943
percentage of none in  AppearancePic  :  97.42990654205607
percentage of none in  SexualAttributes  :  82.4766355140187
percentage of none in  SexMorphology  :  82.00934579439252
percentage of none in  SexColors  :  82.4766355140187
percentage of none in  StrikingFeatures  :  54.20560747663551
percentage of none in  BodyShapeI  :  4.906542056074766
percentage of none in  BodyShapeII  :  46.728971962616825
percentage of none in  Forehead  :  50.70093457943925
percentage of none in  TypeofEyes  :  50.467289719626166
percentage of none in  TypeofMouth  :  50.93457943925234
percentage of none in  PosofMouth  :  48.831775700934585
percentage of none in  MandibleTeeth  :  72.42990654205607
percentage of none in  MandibleTeethT1  :  89.95327102803739
percentage of none in  MandibleTeethT2  :  99.53271028037383
percentage of none in  MandibleRowsMin  :  95.7943925233645
percentage of none in  MandibleRowsMax  :  96.26168224299066
perce

In [34]:
unique_values["BodyShapeI"]

{'elongated': 149,
 'short and / or deep': 54,
 'fusiform / normal': 201,
 'None': 21,
 'eel-like': 3}

In [35]:
unique_values["Forehead"]

{'None': 217,
 'more or less straight': 137,
 'clearly concave': 12,
 'clearly convex': 62}

In [36]:
for i in schema["Dorsal Fin"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

DorsalFinI
{
  "None": 289,
  "more than one spot or stripe": 53,
  "no spots or stripes": 75,
  "one spot or stripe": 11
}
DorsalFinII
{
  "None": 307,
  "no colored margin": 102,
  "colored margin": 19
}
DorsalAttributes
{
  "no striking attributes": 196,
  "None": 184,
  "extending over most of the back length": 36,
  "origin on head, nearly above eye": 2,
  "first fin ray transformed to 'line and (luminous) bait'": 2,
  "other": 4,
  "first fin ray very elongated": 1,
  "last fin rays very elongated": 2,
  "continuous with caudal fin": 1
}
Dfinno
{
  "1.0": 275,
  "None": 102,
  "2.0": 48,
  "3.0": 3
}
DorsalSpinesMin
{
  "None": 119,
  "0.0": 85,
  "7.0": 18,
  "3.0": 14,
  "10.0": 23,
  "1.0": 5,
  "9.0": 36,
  "4.0": 9,
  "6.0": 7,
  "13.0": 13,
  "11.0": 31,
  "12.0": 33,
  "14.0": 5,
  "8.0": 20,
  "2.0": 6,
  "18.0": 1,
  "22.0": 1,
  "5.0": 1,
  "16.0": 1
}
DorsalSpinesMax
{
  "None": 121,
  "0.0": 86,
  "10.0": 23,
  "4.0": 9,
  "12.0": 30,
  "1.0": 2,
  "8.0": 24,
  "11.0"

In [37]:
for i in schema["Pelvic Fins"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

PelvicsAttributes
{
  "more or less normal": 261,
  "None": 157,
  "joint, cup-like": 3,
  "suppressed/absent": 4,
  "other (see diagnosis)": 2,
  "reduced to filaments": 1
}
VPosition
{
  "abdominal": 136,
  "None": 157,
  "thoracic": 112,
  "jugular": 22,
  "absent": 1
}
VPosition2
{
  "None": 180,
  "behind origin of D1": 78,
  "before origin of D1": 89,
  "beneath origin of D1": 81
}
Vspines
{
  "None": 244,
  "0.0": 80,
  "1.0": 95,
  "2.0": 9
}
Vraymin
{
  "None": 222,
  "9.0": 22,
  "6.0": 16,
  "3.0": 30,
  "18.0": 1,
  "7.0": 39,
  "5.0": 41,
  "8.0": 24,
  "4.0": 16,
  "10.0": 8,
  "0.0": 5,
  "2.0": 3,
  "1.0": 1
}
Vraymax
{
  "None": 229,
  "11.0": 11,
  "6.0": 7,
  "4.0": 19,
  "21.0": 1,
  "10.0": 9,
  "8.0": 28,
  "5.0": 41,
  "9.0": 18,
  "7.0": 30,
  "0.0": 5,
  "3.0": 23,
  "12.0": 2,
  "2.0": 3,
  "13.0": 1,
  "1.0": 1
}
VFinletsmin
{
  "None": 199,
  "0.0": 228,
  "2.0": 1
}
VFinletsmax
{
  "None": 189,
  "0.0": 236,
  "2.0": 1,
  "1.0": 2
}


In [38]:
for i in schema["Pectoral Fins"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

PectoralAttributes
{
  "more or less normal": 269,
  "None": 153,
  "very large , lobe-like": 2,
  "used for locomotion": 1,
  "rays very elongated": 3
}
Pspines2
{
  "None": 159,
  "0.0": 249,
  "1.0": 20
}
Praymin
{
  "None": 137,
  "14.0": 74,
  "10.0": 6,
  "12.0": 27,
  "25.0": 1,
  "8.0": 8,
  "11.0": 20,
  "15.0": 38,
  "17.0": 21,
  "13.0": 45,
  "19.0": 9,
  "9.0": 7,
  "16.0": 18,
  "18.0": 12,
  "7.0": 3,
  "6.0": 1,
  "0.0": 1
}
Praymax
{
  "None": 138,
  "17.0": 44,
  "14.0": 46,
  "16.0": 40,
  "30.0": 1,
  "10.0": 2,
  "18.0": 21,
  "13.0": 24,
  "20.0": 12,
  "15.0": 45,
  "21.0": 3,
  "12.0": 12,
  "19.0": 21,
  "11.0": 4,
  "9.0": 5,
  "23.0": 2,
  "22.0": 1,
  "8.0": 3,
  "6.0": 1,
  "24.0": 1,
  "7.0": 1,
  "0.0": 1
}


In [39]:
for i in schema["Anal Fin"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

AnalFinI
{
  "None": 290,
  "no spots or stripes": 88,
  "more than one spot or stripe": 46,
  "one spot or stripe": 4
}
AnalFinII
{
  "None": 306,
  "no colored margin": 104,
  "colored margin": 18
}
Afinno
{
  "None": 132,
  "1.0": 291,
  "2.0": 5
}
AnalFinSpinesMin
{
  "None": 125,
  "0.0": 97,
  "3.0": 104,
  "2.0": 79,
  "1.0": 15,
  "4.0": 8
}
AnalFinSpinesMax
{
  "None": 123,
  "0.0": 101,
  "4.0": 12,
  "3.0": 105,
  "1.0": 15,
  "2.0": 72
}
Araymin
{
  "None": 99,
  "10.0": 18,
  "9.0": 27,
  "11.0": 25,
  "15.0": 13,
  "5.0": 11,
  "8.0": 62,
  "4.0": 2,
  "6.0": 8,
  "7.0": 21,
  "12.0": 18,
  "13.0": 7,
  "14.0": 17,
  "20.0": 4,
  "17.0": 13,
  "28.0": 4,
  "21.0": 11,
  "58.0": 1,
  "19.0": 12,
  "16.0": 15,
  "23.0": 7,
  "53.0": 1,
  "22.0": 1,
  "24.0": 2,
  "18.0": 11,
  "26.0": 1,
  "32.0": 3,
  "45.0": 1,
  "35.0": 1,
  "46.0": 1,
  "72.0": 1,
  "29.0": 3,
  "25.0": 2,
  "107.0": 1,
  "36.0": 1,
  "41.0": 1,
  "80.0": 1,
  "30.0": 1
}
Araymax
{
  "None": 100,
  "22.

In [40]:
for i in schema["Adipose Fin"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

Adifin
{
  "absent": 272,
  "None": 127,
  "present": 29
}


In [41]:
for i in schema["Eyes"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

TypeofEyes
{
  "None": 216,
  "more or less normal": 210,
  "eyes with fixed fatty (adipose) tissue/eyelids": 2
}
EyeLength
{
  "None": 428
}


In [42]:
for i in schema["Barbels"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

BarbelsNo
{
  "None": 235,
  "0.0": 176,
  "6.0": 4,
  "2.0": 4,
  "8.0": 2,
  "4.0": 7
}
BarbelsType
{
  "None": 422,
  "none branched": 5,
  "some branched": 1
}


In [43]:
for i in schema["Caudal Fin"]:
    print(i)
    prt = json.dumps(unique_values[i],indent=2)
    print(prt)

CaudalFinI
{
  "None": 291,
  "more than one spot or stripe": 53,
  "no spots or stripes": 79,
  "one spot or stripe": 5
}
CaudalFinII
{
  "None": 305,
  "no colored margin": 101,
  "colored margin": 22
}
CShape
{
  "forked": 154,
  "None": 143,
  "more or less truncate": 119,
  "other (see remark)": 5,
  "heterocercal": 1,
  "pointed": 6
}
CaudalHeight
{
  "None": 428
}
PeduncleDepth
{
  "None": 428
}
PeduncleLength
{
  "None": 428
}


In [44]:
species_df = pd.read_parquet("FishBase/species.parquet")
taxonomy_map = species_df[['SpecCode', 'Genus', 'Species']]

# 2. Fetch the morphology data
morph_df = pd.read_parquet("FishBase/morphdat.parquet")

# 3. Merge them together on SpecCode
merged_df = pd.merge(morph_df, taxonomy_map, left_on="Speccode",right_on = "SpecCode", how="inner").drop(columns=['Speccode'])

metadata_cols = [
    'autoctr', 'StockCode', 'MorphDatRefNo', 'AppearancePic', 
    'Entered', 'DateEntered', 'Modified', 'DateModified', 'Expert', 
    'DateChecked', 'RemarkSex', 'AddChars', 'SimilarSpecies1', 
    'SimilarSpec1Remarks', 'SimilarSpecies2', 'SimilarSpec2Remarks', 
    'EaseofID', 'OtherRef1', 'OtherRef2', 'TS', 'CommentonTeeth'
]
def get_rounded_mean(series):
    # Calculate the mean, skipping NaNs
    avg = series.mean(skipna=True)
    
    # If the average is NaN (whole group was empty), return None
    if pd.isna(avg):
        return None
        
    # Otherwise, return the safely rounded integer
    return round(avg)
    
# 5. Robust Mode Function
def get_mode_ignore_nan(series):
    clean_series = series.dropna() 
    if clean_series.empty:
        return None 
    return clean_series.mode().iloc[0]

# 6. Dynamically build the aggregation dictionary
print("Building aggregation logic...")
agg_dict = {}

for col in merged_df.columns:
    # Skip taxonomic identifiers and metadata
    if col in ['Genus', 'Species', 'SpecCode'] or col in metadata_cols:
        continue
        
    # Check if the column is numerical (integers or floats)
    if pd.api.types.is_numeric_dtype(merged_df[col]):
        # Apply mean, explicitly skipping NaNs
        agg_dict[col] = get_rounded_mean
    else:
        # Apply mode for text, boolean, or categorical columns
        agg_dict[col] = get_mode_ignore_nan
genus_morphology = merged_df.groupby('Genus').agg(agg_dict).reset_index()
genus_morphology.head()

Building aggregation logic...


,Genus,Females,Males,SexualAttributes,SexMorphology,SexColors,StrikingFeatures,BodyShapeI,BodyShapeII,Forehead,...,PreAnalLength,PostHeadDepth,PostTrunkDepth,MaximumDepth,PeduncleDepth,PeduncleLength,CaudalHeight,PreorbitalLength,EyeLength,GasBladder
0,Aapticheilichthys,0,0,NaN,always different morphology between mature adults,NaN,NaN,fusiform / normal,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,None
1,Aaptosyax,0,0,NaN,NaN,NaN,none,fusiform / normal,NaN,more or less straight,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,None
2,Abactochromis,0,0,NaN,NaN,NaN,NaN,short and / or deep,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,None
3,Abalistes,0,0,no special organs,males alike females,males alike females,striking fins,short and / or deep,compressed,clearly convex,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,None
4,Abantennarius,0,0,NaN,NaN,NaN,striking shape of body,short and / or deep,compressed,more or less straight,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,None


In [45]:
def get_genus(species):
    sp = species.split()
    if len(sp) < 2:
        return species.lower()
    else:
        return sp[0].lower()

def get_feature_genus(genus, col):
    try:
        # .loc[row_condition, column_name] is the safest way to extract a specific cell
        result = genus_morphology.loc[genus_morphology['Genus'].str.lower() == genus.lower(), col]
        
        # Check if the result is empty (i.e., the genus wasn't found in the database)
        if not result.empty:
            return result.iloc[0]
        else:
            return None
            
    except Exception as e:
        print(f"Error fetching {col} for genus {genus}: {e}")
        return None

In [46]:
data_fishBase_mod = {}
for i in species_list_idf_train:
    speccode = get_speccode(i)
    if(speccode == None):
        no_fish.append(i)
        continue
    morph_data = get_morph_data(speccode)
    
    # check if it is empty or not
    json_val = json.loads(morph_data.to_json(orient='records'))
    if(len(json_val) >= 1):
        data_fishBase_mod[i] = json_val[0]
        for j in data_fishBase_mod[i]:
            # print(j)
            if(pd.isna(data_fishBase_mod[i][j])):
                print(get_feature_genus(get_genus(i),j))
                data_fishBase_mod[i][j] = get_feature_genus(get_genus(i),j)
    else:
        no_fish.append(i)

/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))


Error fetching AppearancePic for genus phenacobius: 'AppearancePic'
None
Error fetching AppearancePic for genus phenacobius: 'AppearancePic'
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
Error fetching CommentonTeeth for genus phenacobius: 'CommentonTeeth'
None
Error fetching CommentonTeeth for genus phenacobius: 'CommentonTeeth'
nan
nan
nan
lateral
nan
nan
nan
nan
nan
nan
nan
nan
nan
more than one spot
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
behind origin of D1
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
None
Error fetching Modified for genus phenacobius: 'Modified'
None
Error fetching Modified for genus phenacobius: 'Modified'
Error fetching Expert for genus phenacobius: 'Expert'
None
Error fetching Exp

/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))


Error fetching AppearancePic for genus lepomis: 'AppearancePic'
None
Error fetching AppearancePic for genus lepomis: 'AppearancePic'
nan
nan
different colors during breeding season only
flaps
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
Error fetching CommentonTeeth for genus lepomis: 'CommentonTeeth'
None
Error fetching CommentonTeeth for genus lepomis: 'CommentonTeeth'
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
35.0
47.0
nan
nan
nan
nan
5.0
11.0
11.0
15.0
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
28.0
30.0
no striking attributes
1.0
10.0
12.0
10.0
12.0
absent
0.0
0.0
0.0
0.0
more or less truncate
more or less normal
1.0
3.0
3.0
8.0
11.0
more or less normal
0.0
12.0
14.0
more or less normal
abdominal
before origin of D1
1.0
5.0
5.0
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
None
Error fetching Modified for genus 

/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))


...

/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))


nan
nan
nan
nan
nan
nan
nan
nan
nan
Error fetching CommentonTeeth for genus micropterus: 'CommentonTeeth'
None
Error fetching CommentonTeeth for genus micropterus: 'CommentonTeeth'
ctenoid scales
absent
0.0
present
lateral
present
nan
nan
absent
nan
nan
absent
nan
nan
more than one spot
lateral
on trunk and tail
no spots or stripes
no colored margin
no spots or stripes
no colored margin
no spots or stripes
no colored margin
1.0
65.0
72.0
60.0
68.0
nan
nan
7.0
9.0
11.0
15.0
28.0
31.0
0.0
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
30.0
32.0
no striking attributes
1.0
10.0
10.0
11.0
14.0
absent
0.0
0.0
0.0
0.0
more or less truncate
nan
1.0
4.0
4.0
10.0
11.0
more or less normal
0.0
14.0
16.0
more or less normal
thoracic
before origin of D1
1.0
5.0
13.0
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
None
Error fetching Modified for genus micropterus: 'Modified'
None
Error fetching Modified for genus micropterus: 'Modified'
Error fetching Expert for genus micropterus: 'Expe

/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))


nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
Error fetching CommentonTeeth for genus micropterus: 'CommentonTeeth'
None
Error fetching CommentonTeeth for genus micropterus: 'CommentonTeeth'
ctenoid scales
absent
0.0
present
lateral
present
nan
nan
absent
nan
nan
absent
nan
nan
more than one spot
lateral
on trunk and tail
no spots or stripes
no colored margin
no spots or stripes
no colored margin
no spots or stripes
no colored margin
1.0
65.0
72.0
60.0
68.0
nan
nan
7.0
9.0
11.0
15.0
28.0
31.0
0.0
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
30.0
32.0
no striking attributes
1.0
10.0
10.0
11.0
14.0
absent
0.0
0.0
0.0
0.0
more or less truncate
nan
1.0
4.0
4.0
10.0
11.0
more or less normal
0.0
14.0
16.0
more or less normal
thoracic
before origin of D1
1.0
5.0
13.0
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
nan
None
Error fetching Modified for genus micropterus: 'Modified'
None
Error fetching Modified for genus micropterus: 'Modified'
Error fetching Expert 

/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10: Pandas4Warning: The default 'epoch' date format is deprecated and will be removed in a future version, please use 'iso' date format instead.
  json_val = json.loads(morph_data.to_json(orient='records'))
/tmp/ipykernel_16654/352066058.py:10

In [47]:
data_fishBase_mod

{'phenacobius mirabilis': {'autoctr': 22743,
  'Speccode': 2923,
  'StockCode': 3119,
  'MorphDatRefNo': 86798.0,
  'Females': 0,
  'Males': 0,
  'AppearancePic': None,
  'SexualAttributes': nan,
  'SexMorphology': nan,
  'SexColors': nan,
  'StrikingFeatures': nan,
  'BodyShapeI': 'elongated',
  'BodyShapeII': nan,
  'Forehead': nan,
  'OperculumPresent': 0,
  'TypeofEyes': nan,
  'TypeofMouth': nan,
  'PosofMouth': nan,
  'MandibleTeeth': nan,
  'MandibleTeethT1': nan,
  'MandibleTeethT2': nan,
  'MandibleRowsMin': np.float64(nan),
  'MandibleRowsMax': np.float64(nan),
  'MaxillaTeeth': nan,
  'MaxillaTeethT1': nan,
  'MaxillaTeethT2': nan,
  'MaxillaRowsMin': np.float64(nan),
  'MaxillaRowsMax': np.float64(nan),
  'VomerineTeeth': nan,
  'VomerineTeethT1': nan,
  'VomerineTeethT2': nan,
  'VomerineRowsMin': np.float64(nan),
  'VomerineRowsMax': np.float64(nan),
  'Palatine': nan,
  'PalatineTeethT1': nan,
  'PalatineTeethT2': nan,
  'PalatineRowsMin': np.float64(nan),
  'PalatineRow

In [48]:
# get all unique values for each field with no. of occurances
unique_values_mod = {}
for i in data_fishBase_mod:
    for j in data_fishBase_mod[i]:
        if j not in unique_values_mod:
            unique_values_mod[j] = {}

        if(str(data_fishBase_mod[i][j]) not in unique_values_mod[j]):
            unique_values_mod[j][str(data_fishBase_mod[i][j])] = 0
        print(j)
        unique_values_mod[j][str(data_fishBase_mod[i][j])] += 1

autoctr
Speccode
StockCode
MorphDatRefNo
Females
Males
AppearancePic
SexualAttributes
SexMorphology
SexColors
StrikingFeatures
BodyShapeI
BodyShapeII
Forehead
OperculumPresent
TypeofEyes
TypeofMouth
PosofMouth
MandibleTeeth
MandibleTeethT1
MandibleTeethT2
MandibleRowsMin
MandibleRowsMax
MaxillaTeeth
MaxillaTeethT1
MaxillaTeethT2
MaxillaRowsMin
MaxillaRowsMax
VomerineTeeth
VomerineTeethT1
VomerineTeethT2
VomerineRowsMin
VomerineRowsMax
Palatine
PalatineTeethT1
PalatineTeethT2
PalatineRowsMin
PalatineRowsMax
PharyngealTeeth
PharyngealTeethT1
PharyngealTeethT2
PharyngealRowsMin
PharyngealRowsMax
TeethonTongue
Lipsteeth
DermalTeeth
CommentonTeeth
TypeofScales
Scutes
Keels
HorStripesTTI
HorStripesTTII
VerStripesTTI
VerStripesTTII
VerStripesTTIII
DiaStripesTTI
DiaStripesTTII
DiaStripesTTIII
CurStripesTTI
CurStripesTTII
CurStripesTTIII
SpotsTTI
SpotsTTII
SpotsTTIII
DorsalFinI
DorsalFinII
CaudalFinI
CaudalFinII
AnalFinI
AnalFinII
LateralLinesNo
LLinterrupted
ScalesLateralmin
ScalesLateralmax
P

In [49]:
unique_values_mod

{'autoctr': {'22743': 1,
  '1811': 1,
  '2157': 1,
  '1992': 1,
  '2156': 1,
  '267': 1,
  '2154': 1,
  '2091': 1,
  '18808': 1,
  '2504': 1,
  '19107': 1,
  '19161': 1,
  '1956': 1,
  '2005': 1,
  '249': 1,
  '1131': 1,
  '19106': 1,
  '18806': 1,
  '1991': 1,
  '22469': 1,
  '2155': 1,
  '1894': 1,
  '18876': 1,
  '278': 1,
  '2006': 1,
  '2007': 1,
  '857': 1,
  '250': 1,
  '5987': 1,
  '1254': 1,
  '22452': 1,
  '16791': 1,
  '3067': 1,
  '19105': 1,
  '22746': 1,
  '2008': 1,
  '1994': 1,
  '1249': 1,
  '1993': 1,
  '22451': 1,
  '18809': 1,
  '3449': 1,
  '18961': 1,
  '6643': 1,
  '333': 1,
  '21668': 1,
  '254': 1,
  '1990': 1,
  '255': 1,
  '1938': 1,
  '1988': 1,
  '3016': 1,
  '253': 1,
  '21665': 1,
  '2503': 1,
  '2000': 1,
  '856': 1,
  '1824': 1,
  '12347': 1,
  '1197': 1,
  '809': 1,
  '4028': 1,
  '2722': 1,
  '18920': 1,
  '18787': 1,
  '8062': 1,
  '277': 1,
  '1485': 1,
  '3666': 1,
  '3778': 1,
  '6339': 1,
  '2678': 1,
  '3473': 1,
  '3578': 1,
  '15715': 1,
  '14

In [50]:
percentage_analysis = []
percentage_dict = {}
for i in unique_values_mod:
    perc = 0.0
    if "None" in unique_values_mod[i] or "nan" in unique_values_mod[i]:
        if "None" in unique_values_mod[i] and "nan" in unique_values_mod[i]:    
            print("percentage of none in ",i," : ",((float(unique_values_mod[i]["None"])) + (float(unique_values_mod[i]["nan"]))/428)*100)    
            perc = ((float(unique_values_mod[i]["None"])) + (float(unique_values_mod[i]["nan"]))/428)*100
        elif "None" in unique_values_mod[i]:
            print("percentage of none in ",i," : ",(float(unique_values_mod[i]["None"])/428)*100)
            perc = (float(unique_values_mod[i]["None"])/428)*100
        elif "nan" in unique_values_mod[i]:
            print("percentage of none in ",i," : ",(float(unique_values_mod[i]["nan"])/428)*100)
            perc = (float(unique_values_mod[i]["nan"])/428)*100
    percentage_dict[i] = perc
    percentage_analysis.append((perc,i))

percentage of none in  MorphDatRefNo  :  8.177570093457943
percentage of none in  AppearancePic  :  97.42990654205607
percentage of none in  SexualAttributes  :  68.92523364485982
percentage of none in  SexMorphology  :  60.747663551401864
percentage of none in  SexColors  :  61.915887850467286
percentage of none in  StrikingFeatures  :  30.140186915887853
percentage of none in  BodyShapeI  :  0.9345794392523363
percentage of none in  BodyShapeII  :  19.859813084112147
percentage of none in  Forehead  :  28.738317757009348
percentage of none in  TypeofEyes  :  26.401869158878505
percentage of none in  TypeofMouth  :  25.934579439252335
percentage of none in  PosofMouth  :  22.66355140186916
percentage of none in  MandibleTeeth  :  50.23364485981309
percentage of none in  MandibleTeethT1  :  67.7570093457944
percentage of none in  MandibleTeethT2  :  89.7196261682243
percentage of none in  MandibleRowsMin  :  80.8411214953271
percentage of none in  MandibleRowsMax  :  81.30841121495327


In [51]:
unique_values_mod["BodyShapeI"]

{'elongated': 162,
 'short and / or deep': 55,
 'fusiform / normal': 204,
 'nan': 4,
 'eel-like': 3}

In [52]:
for i in schema["Eyes"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

TypeofEyes
{
  "nan": 113,
  "more or less normal": 312,
  "eyes with fixed fatty (adipose) tissue/eyelids": 2,
  "positioned on stalks, very prominent, or tubular": 1
}
EyeLength
{
  "nan": 408,
  "7.0": 3,
  "6.0": 11,
  "22.0": 1,
  "14.0": 5
}


In [53]:
for i in schema["Pelvic Fins"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

PelvicsAttributes
{
  "more or less normal": 365,
  "nan": 48,
  "joint, cup-like": 6,
  "suppressed/absent": 5,
  "other (see diagnosis)": 2,
  "reduced to filaments": 1,
  "rays very elongated": 1
}
VPosition
{
  "abdominal": 176,
  "thoracic": 159,
  "nan": 44,
  "jugular": 45,
  "absent": 4
}
VPosition2
{
  "behind origin of D1": 108,
  "before origin of D1": 152,
  "beneath origin of D1": 116,
  "nan": 52
}
Vspines
{
  "nan": 89,
  "1.0": 202,
  "0.0": 127,
  "2.0": 10
}
Vraymin
{
  "nan": 74,
  "5.0": 126,
  "7.0": 50,
  "9.0": 31,
  "6.0": 32,
  "3.0": 39,
  "18.0": 1,
  "4.0": 20,
  "8.0": 32,
  "12.0": 2,
  "10.0": 8,
  "2.0": 6,
  "0.0": 5,
  "11.0": 1,
  "1.0": 1
}
Vraymax
{
  "nan": 78,
  "5.0": 122,
  "8.0": 44,
  "11.0": 11,
  "6.0": 22,
  "4.0": 22,
  "21.0": 1,
  "10.0": 16,
  "9.0": 22,
  "14.0": 1,
  "2.0": 6,
  "7.0": 36,
  "0.0": 5,
  "3.0": 33,
  "12.0": 3,
  "13.0": 5,
  "1.0": 1
}
VFinletsmin
{
  "nan": 88,
  "0.0": 336,
  "1.0": 2,
  "2.0": 1,
  "10.0": 1
}
VFin

In [54]:
for i in schema["Barbels"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

BarbelsNo
{
  "nan": 145,
  "0.0": 252,
  "8.0": 8,
  "3.0": 2,
  "6.0": 7,
  "2.0": 7,
  "4.0": 7
}
BarbelsType
{
  "nan": 404,
  "none branched": 22,
  "some branched": 2
}


In [55]:
for i in schema["Caudal Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

CaudalFinI
{
  "nan": 166,
  "no spots or stripes": 150,
  "more than one spot or stripe": 103,
  "one spot or stripe": 9
}
CaudalFinII
{
  "nan": 211,
  "colored margin": 49,
  "no colored margin": 168
}
CShape
{
  "forked": 183,
  "more or less truncate": 194,
  "other (see remark)": 9,
  "heterocercal": 1,
  "nan": 35,
  "pointed": 6
}
CaudalHeight
{
  "nan": 417,
  "26.0": 11
}
PeduncleDepth
{
  "nan": 396,
  "12.0": 3,
  "11.0": 11,
  "15.0": 8,
  "10.0": 7,
  "26.0": 3
}
PeduncleLength
{
  "nan": 402,
  "10.0": 11,
  "9.0": 9,
  "25.0": 4,
  "11.0": 2
}


In [56]:
for i in schema["Adipose Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

Adifin
{
  "absent": 358,
  "present": 43,
  "nan": 27
}


In [57]:
unique_values_mod["Forehead"]

{'nan': 123,
 'clearly convex': 107,
 'clearly concave': 18,
 'more or less straight': 180}

In [58]:
for i in schema["Pectoral Fins"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

PectoralAttributes
{
  "more or less normal": 373,
  "very large , lobe-like": 3,
  "nan": 48,
  "used for locomotion": 1,
  "rays very elongated": 3
}
Pspines2
{
  "nan": 62,
  "0.0": 332,
  "1.0": 34
}
Praymin
{
  "nan": 41,
  "12.0": 51,
  "11.0": 29,
  "14.0": 91,
  "10.0": 10,
  "15.0": 49,
  "25.0": 1,
  "8.0": 17,
  "13.0": 55,
  "16.0": 23,
  "17.0": 25,
  "20.0": 2,
  "19.0": 9,
  "9.0": 7,
  "18.0": 13,
  "7.0": 3,
  "6.0": 1,
  "0.0": 1
}
Praymax
{
  "nan": 42,
  "14.0": 73,
  "17.0": 56,
  "16.0": 54,
  "30.0": 1,
  "10.0": 2,
  "18.0": 26,
  "13.0": 35,
  "15.0": 52,
  "9.0": 13,
  "22.0": 4,
  "20.0": 12,
  "21.0": 5,
  "11.0": 6,
  "12.0": 14,
  "19.0": 24,
  "23.0": 2,
  "8.0": 3,
  "6.0": 1,
  "24.0": 1,
  "7.0": 1,
  "0.0": 1
}


In [59]:
for i in schema["Anal Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

AnalFinI
{
  "nan": 167,
  "no spots or stripes": 165,
  "more than one spot or stripe": 87,
  "one spot or stripe": 9
}
AnalFinII
{
  "nan": 212,
  "no colored margin": 177,
  "colored margin": 39
}
Afinno
{
  "nan": 59,
  "1.0": 364,
  "2.0": 5
}
AnalFinSpinesMin
{
  "nan": 52,
  "3.0": 116,
  "1.0": 28,
  "0.0": 131,
  "2.0": 89,
  "4.0": 12
}
AnalFinSpinesMax
{
  "nan": 51,
  "3.0": 118,
  "2.0": 88,
  "0.0": 134,
  "4.0": 16,
  "1.0": 21
}
Araymin
{
  "nan": 31,
  "8.0": 74,
  "7.0": 35,
  "10.0": 30,
  "9.0": 31,
  "11.0": 27,
  "15.0": 15,
  "5.0": 11,
  "12.0": 19,
  "4.0": 2,
  "14.0": 21,
  "6.0": 12,
  "18.0": 15,
  "13.0": 8,
  "20.0": 4,
  "17.0": 13,
  "28.0": 4,
  "21.0": 11,
  "58.0": 1,
  "19.0": 13,
  "16.0": 17,
  "22.0": 2,
  "23.0": 7,
  "53.0": 1,
  "24.0": 2,
  "26.0": 1,
  "32.0": 3,
  "45.0": 1,
  "35.0": 1,
  "46.0": 1,
  "72.0": 1,
  "29.0": 3,
  "25.0": 4,
  "107.0": 1,
  "49.0": 1,
  "36.0": 1,
  "41.0": 1,
  "80.0": 1,
  "30.0": 1,
  "210.0": 1
}
Araymax
{

In [60]:
for i in schema["Dorsal Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

DorsalFinI
{
  "nan": 165,
  "no spots or stripes": 134,
  "more than one spot or stripe": 111,
  "one spot or stripe": 18
}
DorsalFinII
{
  "nan": 207,
  "no colored margin": 172,
  "colored margin": 49
}
DorsalAttributes
{
  "no striking attributes": 265,
  "nan": 76,
  "extending over most of the back length": 71,
  "origin on head, nearly above eye": 2,
  "first fin ray transformed to 'line and (luminous) bait'": 2,
  "other": 4,
  "first fin ray very elongated": 5,
  "last fin rays very elongated": 2,
  "continuous with caudal fin": 1
}
Dfinno
{
  "1.0": 337,
  "2.0": 65,
  "nan": 23,
  "3.0": 3
}
DorsalSpinesMin
{
  "nan": 44,
  "10.0": 33,
  "1.0": 28,
  "0.0": 110,
  "7.0": 19,
  "9.0": 42,
  "14.0": 6,
  "3.0": 15,
  "4.0": 10,
  "6.0": 7,
  "13.0": 15,
  "11.0": 32,
  "12.0": 35,
  "8.0": 20,
  "2.0": 8,
  "18.0": 1,
  "22.0": 1,
  "5.0": 1,
  "16.0": 1
}
DorsalSpinesMax
{
  "nan": 43,
  "12.0": 43,
  "1.0": 26,
  "0.0": 110,
  "10.0": 26,
  "11.0": 27,
  "20.0": 2,
  "4.0": 

In [61]:
unique_values_mod["Adifin"]

{'absent': 358, 'present': 43, 'nan': 27}

In [62]:
# do something about fish not present in fishbase
no_fish

['notropis texanus',
 'notropis stramineus',
 'notropis topeka',
 'notropis hudsonius',
 'notropis telescopus',
 'hybopsis dorsalis',
 'notropis boops',
 'notropis heterolepis',
 'cottus bairdii',
 'notropis longirostris',
 'notropis wickliffi',
 'notropis rubellus',
 'notropis heterodon',
 'notropis percobromus',
 'notropis leuciodus',
 'notropis scepticus',
 'notropis volucellus',
 'chaenobryttus gulosus',
 'noturus gyrinus',
 'lepomis marginatus',
 'notropis anogenus',
 'notropis nubilus',
 'enneacanthus obesus',
 'lepomis punctatus',
 'notropis chalybaeus',
 'notropis lutipinnis',
 'noturus miurus',
 'notropis buchanani',
 'notropis procne',
 'notropis chiliticus',
 'cottus perplexus',
 'lepomis symmetricus',
 'notropis xaenocephalus',
 'notropis greenei',
 'noturus eleutherus',
 'notropis chihuahua',
 'notropis petersoni',
 'hybopsis amnis',
 'notropis baileyi',
 'notropis cummingsae',
 'noturus insignis',
 'noturus leptacanthus',
 'notropis photogenis',
 'notropis micropteryx',
 

In [63]:
unique_values_mod["OperculumPresent"]

{'0': 224, '-1': 204}

In [64]:
percentage_analysis.sort()

In [65]:
percentage_analysis

[(0.0, 'DateEntered'),
 (0.0, 'DateModified'),
 (0.0, 'Entered'),
 (0.0, 'Females'),
 (0.0, 'LLinterrupted'),
 (0.0, 'Males'),
 (0.0, 'Notched'),
 (0.0, 'OperculumPresent'),
 (0.0, 'Speccode'),
 (0.0, 'StockCode'),
 (0.0, 'autoctr'),
 (0.9345794392523363, 'BodyShapeI'),
 (5.373831775700935, 'Dfinno'),
 (6.308411214953271, 'Adifin'),
 (7.242990654205607, 'Araymin'),
 (7.476635514018691, 'Araymax'),
 (7.943925233644859, 'DorsalSoftRaysMin'),
 (8.177570093457943, 'CShape'),
 (8.177570093457943, 'DorsalSoftRaysMax'),
 (8.177570093457943, 'MorphDatRefNo'),
 (9.579439252336448, 'Praymin'),
 (9.813084112149532, 'Praymax'),
 (10.046728971962617, 'DorsalSpinesMax'),
 (10.2803738317757, 'DorsalSpinesMin'),
 (10.2803738317757, 'VPosition'),
 (11.214953271028037, 'PectoralAttributes'),
 (11.214953271028037, 'PelvicsAttributes'),
 (11.91588785046729, 'AnalFinSpinesMax'),
 (12.149532710280374, 'AnalFinSpinesMin'),
 (12.149532710280374, 'VPosition2'),
 (13.785046728971961, 'Afinno'),
 (14.25233644859

# json structure:
- head (forehead)
    - forehead
        - clearly convex ->
        - clearly concave ->
        - more or less straight ->
- barbels
    - barbels no. -> numerical
    - barbels type ->
        - none branched
        - some branched
- dorsal fin
    - DorsalFinI
        - no spot or stripes->
        - more then one spot or stripe->
        - one spot or stripe->
    - DorsalFinII
        - no coloured margin->
        - coloured margin->
    - Dorsal Attributes
        - "extending over most of the back length": 71,
        - "origin on head, nearly above eye": 2,
        - "first fin ray transformed to 'line and (luminous) bait'": 2,
        - "other": 4,
        - "first fin ray very elongated": 5,
        - "last fin rays very elongated": 2,
        - "continuous with caudal fin": 1
    - Dfinno -> numerical
    - Notched -> 0, -1
    - Dorsal spines min
    - Dorsal spines max
    - Dorsal soft rays min
    - Dorsal soft rays max
- pectoral fin
```
PectoralAttributes
{
  "more or less normal": 373,
  "very large , lobe-like": 3,
  "nan": 48,
  "used for locomotion": 1,
  "rays very elongated": 3
}
Pspines2
{
  "nan": 62,
  "0.0": 332,
  "1.0": 34
}
Praymin
{
  
}
Praymax
{
  
```
- pelvic fin
- anal fin
- adipose fin
- caudal fin
- body shape
- operculum present

In [66]:
for i in schema:
    print(i)

Whole Body
Head
Barbels
Eyes
Mouth and Teeth
Gills
Skin, Scales and Coloration
Dorsal Fin
Adipose Fin
Caudal Fin
Anal Fin
Pectoral Fins
Pelvic Fins
Internal Anatomy
Sex and Reproduction
misc


In [67]:
schema["Gills"]

['OperculumPresent',
 'GillCleftsNo',
 'Spiracle',
 'GillRakersLowMin',
 'GillRakersLowMax',
 'GillRakersUpMin',
 'GillRakersUpMax',
 'GillRakersTotalMin',
 'GillRakersTotalMax']

In [68]:
data_fishBase_mod

{'phenacobius mirabilis': {'autoctr': 22743,
  'Speccode': 2923,
  'StockCode': 3119,
  'MorphDatRefNo': 86798.0,
  'Females': 0,
  'Males': 0,
  'AppearancePic': None,
  'SexualAttributes': nan,
  'SexMorphology': nan,
  'SexColors': nan,
  'StrikingFeatures': nan,
  'BodyShapeI': 'elongated',
  'BodyShapeII': nan,
  'Forehead': nan,
  'OperculumPresent': 0,
  'TypeofEyes': nan,
  'TypeofMouth': nan,
  'PosofMouth': nan,
  'MandibleTeeth': nan,
  'MandibleTeethT1': nan,
  'MandibleTeethT2': nan,
  'MandibleRowsMin': np.float64(nan),
  'MandibleRowsMax': np.float64(nan),
  'MaxillaTeeth': nan,
  'MaxillaTeethT1': nan,
  'MaxillaTeethT2': nan,
  'MaxillaRowsMin': np.float64(nan),
  'MaxillaRowsMax': np.float64(nan),
  'VomerineTeeth': nan,
  'VomerineTeethT1': nan,
  'VomerineTeethT2': nan,
  'VomerineRowsMin': np.float64(nan),
  'VomerineRowsMax': np.float64(nan),
  'Palatine': nan,
  'PalatineTeethT1': nan,
  'PalatineTeethT2': nan,
  'PalatineRowsMin': np.float64(nan),
  'PalatineRow

In [69]:
# create the final JSON for the 428 species present. The rest 200 can be seen later
# structure:
# parts - head/fins/etc.
#     attributes - 
#         values - (if value is not numerical we keep all of them and select the one we need)
import numpy as np
def is_numeric(value):
    # 1. The VIP Pass: Allow ANY Numpy float to pass (including their NaNs)
    if isinstance(value, np.floating):
        return True
        
    # 2. Block the string "nan" 
    if isinstance(value, str) and value.strip().lower() == 'nan':
        return False
        
    # 3. Block all OTHER types of missing values (None, pd.NaT, standard Python float NaN)
    if pd.isna(value):
        return False
        
    # 4. Check if it's a valid number string or standard Python int/float
    try:
        float(value)
        return True
    except ValueError:
        return False


custom_schema = ["Barbels","Dorsal Fin","Adipose Fin","Caudal Fin","Anal Fin","Pectoral Fins","Pelvic Fins"]
fb_species_char = {}
for i in data_fishBase_mod:
    fb_species_char[i] = {}
    for j in custom_schema:
        fb_species_char[i][j] = {}
        for k in schema[j]:
            if(percentage_dict[k] > 99):
                continue
            # check if data is numeric
            if(is_numeric(data_fishBase_mod[i][k])):
                fb_species_char[i][j][k] = float(data_fishBase_mod[i][k])
            elif("present" in unique_values_mod[k] or "absent" in unique_values_mod[k]):
                fb_species_char[i][j][k] = data_fishBase_mod[i][k]
            else:
                fb_species_char[i][j][k] = {}
                for l in unique_values_mod[k]:
                    if(data_fishBase_mod[i][k] == l):
                        fb_species_char[i][j][k][l] = True
                    else:
                        fb_species_char[i][j][k][l] = False
                if(pd.isna(data_fishBase_mod[i][k])):
                    fb_species_char[i][j][k]['nan'] = True
                    
    fb_species_char[i]["OperculumPresent"] = data_fishBase_mod[i]["OperculumPresent"]
    fb_species_char[i]["Body"] = {}
    fb_species_char[i]["Body"]["BodyShapeI"] = {k : data_fishBase_mod[i]["BodyShapeI"] == k for k in unique_values_mod["BodyShapeI"]}
    fb_species_char[i]["Body"]["BodyShapeII"] = {k : data_fishBase_mod[i]["BodyShapeII"] == k for k in unique_values_mod["BodyShapeII"]}

    fb_species_char[i]["Forehead"] = {k : data_fishBase_mod[i]["Forehead"] == k for k in unique_values_mod["Forehead"]}
    if(pd.isna(data_fishBase_mod[i]["Forehead"])):
        fb_species_char[i]["Forehead"]['nan'] = True
    

In [70]:
def get_df_data(df,species,col):
    try:
        df2 = df[df['standardized_species'].str.lower() == species.lower()]
        val = df2.iloc[0][col]
        return val
    except Exception as e:
        print(e)
        return None

In [71]:
for i in fb_species_char:
    fb_species_char[i]["Barbels"]["hasBarbels"] = float(get_df_data(df_idf_train,i,"barbel"))
    fb_species_char[i]["Adipose Fin"]["Adifin"] = float(get_df_data(df_idf_train,i,"adipose_fin"))
    fb_species_char[i]["Pelvic Fins"]["hasPelvicFin"] = float(get_df_data(df_idf_train,i,"pelvic_fin"))
    fb_species_char[i]["Dorsal Fin"]["hasMultiple"] = float(get_df_data(df_idf_train,i,"multiple_dorsal_fin"))

In [72]:
fb_species_char

{'phenacobius mirabilis': {'Barbels': {'BarbelsNo': nan,
   'BarbelsType': {'nan': True,
    'none branched': False,
    'some branched': False},
   'hasBarbels': 1.0},
  'Dorsal Fin': {'DorsalFinI': {'nan': True,
    'no spots or stripes': False,
    'more than one spot or stripe': False,
    'one spot or stripe': False},
   'DorsalFinII': {'nan': True,
    'no colored margin': False,
    'colored margin': False},
   'DorsalAttributes': {'no striking attributes': True,
    'nan': False,
    'extending over most of the back length': False,
    'origin on head, nearly above eye': False,
    "first fin ray transformed to 'line and (luminous) bait'": False,
    'other': False,
    'first fin ray very elongated': False,
    'last fin rays very elongated': False,
    'continuous with caudal fin': False},
   'Dfinno': 1.0,
   'DorsalSpinesMin': nan,
   'DorsalSpinesMax': nan,
   'Notched': 0.0,
   'DorsalSoftRaysMin': nan,
   'DorsalSoftRaysMax': nan,
   'DFinletsmin': nan,
   'DFinletsmax':

In [73]:
with open("final_clsf_428_fb.json","w") as f:
    json.dump(fb_species_char,f)


In [74]:
print(data_fishBase_mod["phenacobius mirabilis"]["DorsalFinI"])

nan


In [75]:
# organize percentage_dict in terms of body parts
percentage_dict_org = {}
for i in schema:
    percentage_dict_org[i] = {}
    for j in schema[i]:
        percentage_dict_org[i][j] = percentage_dict[j]


In [76]:
with open("final_attributes_percs.json","w") as f:
    json.dump(percentage_dict_org,f)

# diagnostics

In [77]:
len(species_list_idf_train)

628

In [78]:
len(set(no_fish))

200

# parts:
- foreheaf
- forsal fin
- Adipose fin
- Caudal fin
- Anal Fin
- Pelvic Fin
- Pectoral Fin
- barbels
- body shape
- gills

In [79]:
for i in schema["Dorsal Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

DorsalFinI
{
  "nan": 165,
  "no spots or stripes": 134,
  "more than one spot or stripe": 111,
  "one spot or stripe": 18
}
DorsalFinII
{
  "nan": 207,
  "no colored margin": 172,
  "colored margin": 49
}
DorsalAttributes
{
  "no striking attributes": 265,
  "nan": 76,
  "extending over most of the back length": 71,
  "origin on head, nearly above eye": 2,
  "first fin ray transformed to 'line and (luminous) bait'": 2,
  "other": 4,
  "first fin ray very elongated": 5,
  "last fin rays very elongated": 2,
  "continuous with caudal fin": 1
}
Dfinno
{
  "1.0": 337,
  "2.0": 65,
  "nan": 23,
  "3.0": 3
}
DorsalSpinesMin
{
  "nan": 44,
  "10.0": 33,
  "1.0": 28,
  "0.0": 110,
  "7.0": 19,
  "9.0": 42,
  "14.0": 6,
  "3.0": 15,
  "4.0": 10,
  "6.0": 7,
  "13.0": 15,
  "11.0": 32,
  "12.0": 35,
  "8.0": 20,
  "2.0": 8,
  "18.0": 1,
  "22.0": 1,
  "5.0": 1,
  "16.0": 1
}
DorsalSpinesMax
{
  "nan": 43,
  "12.0": 43,
  "1.0": 26,
  "0.0": 110,
  "10.0": 26,
  "11.0": 27,
  "20.0": 2,
  "4.0": 

In [80]:
for i in schema["Adipose Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

Adifin
{
  "absent": 358,
  "present": 43,
  "nan": 27
}


In [81]:
for i in schema["Caudal Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

CaudalFinI
{
  "nan": 166,
  "no spots or stripes": 150,
  "more than one spot or stripe": 103,
  "one spot or stripe": 9
}
CaudalFinII
{
  "nan": 211,
  "colored margin": 49,
  "no colored margin": 168
}
CShape
{
  "forked": 183,
  "more or less truncate": 194,
  "other (see remark)": 9,
  "heterocercal": 1,
  "nan": 35,
  "pointed": 6
}
CaudalHeight
{
  "nan": 417,
  "26.0": 11
}
PeduncleDepth
{
  "nan": 396,
  "12.0": 3,
  "11.0": 11,
  "15.0": 8,
  "10.0": 7,
  "26.0": 3
}
PeduncleLength
{
  "nan": 402,
  "10.0": 11,
  "9.0": 9,
  "25.0": 4,
  "11.0": 2
}


In [82]:
for i in schema["Anal Fin"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

AnalFinI
{
  "nan": 167,
  "no spots or stripes": 165,
  "more than one spot or stripe": 87,
  "one spot or stripe": 9
}
AnalFinII
{
  "nan": 212,
  "no colored margin": 177,
  "colored margin": 39
}
Afinno
{
  "nan": 59,
  "1.0": 364,
  "2.0": 5
}
AnalFinSpinesMin
{
  "nan": 52,
  "3.0": 116,
  "1.0": 28,
  "0.0": 131,
  "2.0": 89,
  "4.0": 12
}
AnalFinSpinesMax
{
  "nan": 51,
  "3.0": 118,
  "2.0": 88,
  "0.0": 134,
  "4.0": 16,
  "1.0": 21
}
Araymin
{
  "nan": 31,
  "8.0": 74,
  "7.0": 35,
  "10.0": 30,
  "9.0": 31,
  "11.0": 27,
  "15.0": 15,
  "5.0": 11,
  "12.0": 19,
  "4.0": 2,
  "14.0": 21,
  "6.0": 12,
  "18.0": 15,
  "13.0": 8,
  "20.0": 4,
  "17.0": 13,
  "28.0": 4,
  "21.0": 11,
  "58.0": 1,
  "19.0": 13,
  "16.0": 17,
  "22.0": 2,
  "23.0": 7,
  "53.0": 1,
  "24.0": 2,
  "26.0": 1,
  "32.0": 3,
  "45.0": 1,
  "35.0": 1,
  "46.0": 1,
  "72.0": 1,
  "29.0": 3,
  "25.0": 4,
  "107.0": 1,
  "49.0": 1,
  "36.0": 1,
  "41.0": 1,
  "80.0": 1,
  "30.0": 1,
  "210.0": 1
}
Araymax
{

In [83]:
for i in schema["Pelvic Fins"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

PelvicsAttributes
{
  "more or less normal": 365,
  "nan": 48,
  "joint, cup-like": 6,
  "suppressed/absent": 5,
  "other (see diagnosis)": 2,
  "reduced to filaments": 1,
  "rays very elongated": 1
}
VPosition
{
  "abdominal": 176,
  "thoracic": 159,
  "nan": 44,
  "jugular": 45,
  "absent": 4
}
VPosition2
{
  "behind origin of D1": 108,
  "before origin of D1": 152,
  "beneath origin of D1": 116,
  "nan": 52
}
Vspines
{
  "nan": 89,
  "1.0": 202,
  "0.0": 127,
  "2.0": 10
}
Vraymin
{
  "nan": 74,
  "5.0": 126,
  "7.0": 50,
  "9.0": 31,
  "6.0": 32,
  "3.0": 39,
  "18.0": 1,
  "4.0": 20,
  "8.0": 32,
  "12.0": 2,
  "10.0": 8,
  "2.0": 6,
  "0.0": 5,
  "11.0": 1,
  "1.0": 1
}
Vraymax
{
  "nan": 78,
  "5.0": 122,
  "8.0": 44,
  "11.0": 11,
  "6.0": 22,
  "4.0": 22,
  "21.0": 1,
  "10.0": 16,
  "9.0": 22,
  "14.0": 1,
  "2.0": 6,
  "7.0": 36,
  "0.0": 5,
  "3.0": 33,
  "12.0": 3,
  "13.0": 5,
  "1.0": 1
}
VFinletsmin
{
  "nan": 88,
  "0.0": 336,
  "1.0": 2,
  "2.0": 1,
  "10.0": 1
}
VFin

In [84]:
for i in schema["Pectoral Fins"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

PectoralAttributes
{
  "more or less normal": 373,
  "very large , lobe-like": 3,
  "nan": 48,
  "used for locomotion": 1,
  "rays very elongated": 3
}
Pspines2
{
  "nan": 62,
  "0.0": 332,
  "1.0": 34
}
Praymin
{
  "nan": 41,
  "12.0": 51,
  "11.0": 29,
  "14.0": 91,
  "10.0": 10,
  "15.0": 49,
  "25.0": 1,
  "8.0": 17,
  "13.0": 55,
  "16.0": 23,
  "17.0": 25,
  "20.0": 2,
  "19.0": 9,
  "9.0": 7,
  "18.0": 13,
  "7.0": 3,
  "6.0": 1,
  "0.0": 1
}
Praymax
{
  "nan": 42,
  "14.0": 73,
  "17.0": 56,
  "16.0": 54,
  "30.0": 1,
  "10.0": 2,
  "18.0": 26,
  "13.0": 35,
  "15.0": 52,
  "9.0": 13,
  "22.0": 4,
  "20.0": 12,
  "21.0": 5,
  "11.0": 6,
  "12.0": 14,
  "19.0": 24,
  "23.0": 2,
  "8.0": 3,
  "6.0": 1,
  "24.0": 1,
  "7.0": 1,
  "0.0": 1
}


In [85]:
for i in schema["Barbels"]:
    print(i)
    prt = json.dumps(unique_values_mod[i],indent=2)
    print(prt)

BarbelsNo
{
  "nan": 145,
  "0.0": 252,
  "8.0": 8,
  "3.0": 2,
  "6.0": 7,
  "2.0": 7,
  "4.0": 7
}
BarbelsType
{
  "nan": 404,
  "none branched": 22,
  "some branched": 2
}


In [86]:
unique_values_mod["Forehead"]

{'nan': 123,
 'clearly convex': 107,
 'clearly concave': 18,
 'more or less straight': 180}

In [87]:
unique_values_mod["OperculumPresent"]

{'0': 224, '-1': 204}

In [88]:
unique_values_mod["BodyShapeI"]

{'elongated': 162,
 'short and / or deep': 55,
 'fusiform / normal': 204,
 'nan': 4,
 'eel-like': 3}

In [89]:
unique_values_mod["BodyShapeII"]

{'nan': 85,
 'compressed': 194,
 'circular': 57,
 'oval': 89,
 'angular': 2,
 'other (see Diagnosi': 1}

In [90]:
set(no_fish)

{'acanthurus bahianus',
 'adinia xenica',
 'antennatus coccineus',
 'antennatus nummifer',
 'apeltes quadracus',
 'atractosteus tristoechus',
 'aulotrachichthys prosthemius',
 'aztecula sallaei',
 'botia dario',
 'brachyrhaphis cascajalensis',
 'brycinus nurse',
 'catostomus clarkii',
 'centropyge loricula',
 'chaenobryttus gulosus',
 'champsodon snyderi',
 'channa asiatica',
 'chiloglanis niloticus',
 'chlorophthalmus albatrossis',
 'chlorophthalmus nigromarginatus',
 'chrysichthys ansorgii',
 'codoma ornata',
 'coregonus zenithicus',
 'coris debueni',
 'cottus asperrimus',
 'cottus baileyi',
 'cottus bairdii',
 'cottus girardi',
 'cottus greenei',
 'cottus gulosus',
 'cottus klamathensis',
 'cottus perplexus',
 'cottus pitensis',
 'cottus princeps',
 'cyprinodon bifasciatus',
 'dussumieria acuta',
 'enneacanthus chaetodon',
 'enneacanthus obesus',
 'entomacrodus marmoratus',
 'erisphex simplex',
 'etheostoma microperca',
 'etheostoma stigmaeum',
 'etheostoma zonale',
 'floridichthys 